# Volumetric Surface reconstruction

In todays exercise, we will reconstruct a surface from a point cloud obtained by a structured light scan.

In [19]:
from pygel3d import hmesh, jupyter_display as jd
jd.set_export_mode(True)
import numpy as np
from numpy.linalg import norm
from math import exp,floor,sqrt
from random import shuffle
array = np.array

### Part 1: Preliminaries

A few tools are required and therefore defined below

In [20]:
def Gaussian(p0,p,ssq):
    """ Compute the value at p of a Gaussian centered at p0. Standard deviation ssq. """
    v = p - p0
    return exp(-v@v/ssq)

def voxel_neighbourhood(volume_dimensions, pi):
    """ This is a generator that allows us to loop over voxels in the predefined volume
    neighborhood around pi """
    for i,j,k in np.ndindex((5,5,5)):
        yield pi[0]-2+i, pi[1]-2+j, pi[2]-2+k

class XForm:
    """ This class transforms grid indices to the corresponding location
    in a 3D bounding box and back"""
    def __init__(self,Plow,Phigh,dims):
        """ Initialize with the minimum coordinates corner Plow, maximum coordinates
        corner Phigh, and the voxel grid dimensions. """
        self.dims = array(dims)
        self.Plow = array(Plow)
        self.Phigh = array(Phigh)
        self.scaling = (self.Phigh - self.Plow) / self.dims
        self.inv_scaling = self.dims / (self.Phigh - self.Plow)
    def map(self,pi):
        """ map transforms a grid point to the point in space that corresponds to 
        the grid point. """
        return self.scaling * array(pi) + self.Plow
    def inv_map(self,p):
        return array((p-self.Plow) * self.inv_scaling,dtype=int)


### Part 2: Loading data and specifying a subset to use
We now load the point cloud and select a subset of points. Once your code is running, play around with the number of points that you load to get a better result in a reasonable time.

In [36]:
# Specify how many points to use, experiment with this number <----------------------
NO_POINTS = 10000

# Below, we load the data set. 
print("Loading point set ...")
f = open("owl-lines.off")
coords = [list(map(float, l.split())) for l in f.readlines()]
shuffle(coords)
coords = array(coords)
point_mat = array(coords[0:NO_POINTS,0:3])
norm_mat = array(coords[0:NO_POINTS,3:6])

#Create and slightly expand bbox
corner_min = point_mat.min(0)
corner_max = point_mat.max(0)
print("bbox : ", corner_min, corner_max)
diag_vec = corner_max - corner_min
diag = norm(diag_vec)
corner_min -= 0.1 * diag_vec
corner_max += 0.1 * diag_vec

Loading point set ...
bbox :  [ -43.8961 -139.937   599.262 ] [ 73.0251  93.7231 768.635 ]


### Part 3: Volume dimensions
Here we compute the volume dimensions such that the longest axis is leng_axis. Afterwards we compute the scaling factor of the Gauss kernel. Once your code is up and running play around with these two values to achieve a better solution.

In [56]:
# Once the code works, experiment with the dimensions of the volume. <----------------------
leng_axis=256.0
volume_dimensions = np.asarray((leng_axis/ diag_vec.max()) * diag_vec,dtype=int)
print("Volume dimension : ", volume_dimensions)

# Initialize the volume that will contain sum of distance values
volume = np.zeros(volume_dimensions,dtype=float)

# Initialize the weight volume
volume_w = np.zeros(volume_dimensions,dtype=float)

# Create a transform mapping between voxel grid and point bbox.
xform = XForm(corner_min,corner_max,volume.shape)

# Compute 'sigma square' (the scaling factor for the Gauss kernel) based on the length
# of the bbox diagonal. Experiment with this number <-------------------------
ssq = 3

Volume dimension :  [128 256 185]


### Part 4: The Actual Exercise
We need to compute a contribution to the volume for every point in the selected subset. This is done by iterating over all voxels in a neighborhood around a given point. Enter your code here.

In [57]:
# Iterate over all points
# for each point compute its contribution to the local neighborhood.
# Finally, normalize the volume

for p,n in zip(point_mat, norm_mat):
    voxel = xform.inv_map(p)
    for v in voxel_neighbourhood(volume_dimensions, voxel):
        x = xform.map(v)
        d = n @ (x - p)
        w = Gaussian(x, p, ssq)
        volume[v] += w * d
        volume_w[v] += w

volume = volume / volume_w

C:\Users\Bruger\AppData\Local\Temp\ipykernel_2436\2836971396.py:14: RuntimeWarning:

invalid value encountered in divide



### Part 5: Visualize
In this part, we polygonize and display the number vertices and faces, aswell as the boundary of the box.

In [58]:
m = hmesh.volumetric_isocontour(volume, bbox_min=corner_min, bbox_max=corner_max)
jd.display(m)

### Part 7: Questions
- Why use volumetric reconstruction instead of Delaunay triangulation, say? 
- What is the purpose of the XForm class and how does it work?
- What is your experience about the number of points you used?
- What is your experience about the influence of setting the volume dimensions (leng_axis)?
- What is your experience about the Gauss kernel scaling factor (ssq)?

**Why use volumetric reconstruction instead of Delaunay triangulation, say?**

The 2D Delaunay triangulation wouldn't work on an owl, because the algorithm needs one point above each (x,y). In that way we can project the points to 0, triangulate and then raise the points back to the correct height. For owl, and in general 3D objects scanned around them, there is more than one point at the same x,y getting different z values. 

When it comes to 3D Delaunay, it gives a very big number of triangles, afterwards we need to label tetrahedra to find out whether they are outside or inside our object, which is difficult due to the noise. Lastly, the noise stays in the output, as Delaunay uses scanned points to generate the output, even the noisy ones.

**What is the purpose of the XForm class and how does it work?**

The problem we need to solve is that we are dealing with 2 coordinate systems - one from the scanner and one from the grid coordinates that we are implementing. On the grid, our voxels are numbered, where the numbers become their position in the array. We now need to translate between position of the point in real world coordinate, which could be a float number and position of the voxel in our grid which is an integer. This is why we use XForm and map or inv_map, for that exact translation. It method inv_map does translation, scaling and rounding. In translation substracts the box's low corner, so we can measure positions from, where voxel counting starts, in scaling it divides by the voxel size. 

**What is your experience about the number of points you used?**

For 100 points - I can only see some small surfaces spread around

For 1000 points - I can see some shapes but there is a lot of holes between them

For 10000 points - the surface starts resambling an owl but it is not there yet, computation time is increasing 

**What is your experience about the influence of setting the volume dimensions (leng_axis)?**

For 256/2 - I can see largers boxes (could compare it to a lower resolution)

For 256*2 - The change gives holes in the shape and is slower to compute

**What is your experience about the Gauss kernel scaling factor (ssq)?**

It is difficult to see the difference on display. I tried changing the value between 1 and 20. 